# Visualize Generation Rollouts

Load qpos trajectories from the RGM and PULSE generation rollout H5 files and render them for comparison.

In [1]:
import os

os.environ["XLA_PYTHON_CLIENT_PREALLOCATE"] = "false"
os.environ["MUJOCO_GL"] = "egl"
os.environ["PYOPENGL_PLATFORM"] = "egl"

import h5py
import numpy as np
import mujoco
import mediapy as media
import matplotlib.pyplot as plt
from pathlib import Path
from scamper.environment.rodent import consts as rodent_consts

## Configuration

In [2]:
# ============ PATHS ============
RGM_PATH = "/home/mila/a/aidan.sirbu/SCAMPER/data/generation_rollout/generation_rollout_rgm_54.h5"
PULSE_PATH = "/home/mila/a/aidan.sirbu/SCAMPER/data/generation_rollout/generation_rollout_PULSE_fc_49.h5"

# ============ RENDERING ============
CLIP_IDX = 100  # Clip index to visualize (0-841)
RENDER_FPS = 50
CAMERA_NAME = "close_profile-rodent"
RENDER_HEIGHT = 480
RENDER_WIDTH = 640

## Load Datasets

In [3]:
def load_h5_datasets(path):
    """Load all datasets from an H5 file into a dict."""
    datasets = {}
    with h5py.File(path, "r") as f:
        print(f"File: {Path(path).name}")
        for key in sorted(f.keys()):
            print(f"  {key}: {f[key].shape}")
            datasets[key] = f[key][:]
    print()
    return datasets

rgm_data = load_h5_datasets(RGM_PATH)
pulse_data = load_h5_datasets(PULSE_PATH)

File: generation_rollout_rgm_54.h5
  original_qpos: (842, 250, 74)
  rgm_deterministic_latents: (842, 490, 16)
  rgm_deterministic_qpos: (842, 490, 74)
  rgm_logvar_-0.5_latents: (842, 490, 16)
  rgm_logvar_-0.5_qpos: (842, 490, 74)
  rgm_logvar_-1_latents: (842, 490, 16)
  rgm_logvar_-1_qpos: (842, 490, 74)
  rgm_logvar_-2_latents: (842, 490, 16)
  rgm_logvar_-2_qpos: (842, 490, 74)
  rgm_logvar_-3_latents: (842, 490, 16)
  rgm_logvar_-3_qpos: (842, 490, 74)
  rgm_logvar_-4_latents: (842, 490, 16)
  rgm_logvar_-4_qpos: (842, 490, 74)
  rgm_logvar_0_latents: (842, 490, 16)
  rgm_logvar_0_qpos: (842, 490, 74)
  rgm_predicted_logvar_latents: (842, 490, 16)
  rgm_predicted_logvar_qpos: (842, 490, 74)
  student_encoder_decoder_latents: (842, 490, 16)
  student_encoder_decoder_qpos: (842, 490, 74)

File: generation_rollout_PULSE_fc_49.h5
  original_qpos: (842, 250, 74)
  prior_deterministic_latents: (842, 490, 16)
  prior_deterministic_qpos: (842, 490, 74)
  prior_logvar_-0.5_latents: (842,

## Build MuJoCo Model for Rendering

In [4]:
# Build combined arena+rodent model (74 DOF qpos)
walker_xml = str(rodent_consts.RODENT_NO_TAIL_COLLISION_XML)
arena_xml = str(rodent_consts.ARENA_XML_PATH)

arena_spec = mujoco.MjSpec.from_file(arena_xml)
rodent_spec = mujoco.MjSpec.from_file(walker_xml)

frame = arena_spec.worldbody.add_frame(pos=(0, 0, 0), quat=(1, 0, 0, 0))
spawn_body = frame.attach_body(rodent_spec.body("walker"), "", suffix="-rodent")
spawn_body.add_freejoint(name="root")

model = arena_spec.compile()
data = mujoco.MjData(model)

print(f"Model qpos dim: {model.nq}")
print(f"Available cameras:")
for i in range(model.ncam):
    print(f"  {i}: {model.camera(i).name}")

Model qpos dim: 74
Available cameras:
  0: close_profile-rodent
  1: back-rodent
  2: side-rodent
  3: close_side_hind_R-rodent
  4: close_side_front_R-rodent
  5: close_side_hind_L-rodent
  6: close_side_front_L-rodent
  7: front-rodent
  8: close_front-rodent
  9: left-rodent
  10: right-rodent
  11: side_alt-rodent
  12: top-rodent
  13: egocentric-rodent


## Rendering Function

In [8]:
def render_qpos_trajectory(
    qpos_trajectory: np.ndarray,
    camera_name: str = CAMERA_NAME,
    height: int = RENDER_HEIGHT,
    width: int = RENDER_WIDTH,
) -> list[np.ndarray]:
    """Render a qpos trajectory to a list of RGB frames."""
    renderer = mujoco.Renderer(model, height=height, width=width)
    frames = []
    for qpos in qpos_trajectory:
        data.qpos[:] = qpos
        mujoco.mj_forward(model, data)
        renderer.update_scene(data, camera=camera_name)
        frames.append(renderer.render().copy())
    renderer.close()
    return frames

In [9]:
# Which qpos datasets to render from each file
RGM_DATASETS = [
    "original_qpos",
    "student_encoder_decoder_qpos",
    "rgm_deterministic_qpos",
    "rgm_predicted_logvar_qpos",
    "rgm_logvar_-2_qpos",
    "rgm_logvar_0_qpos",
]

PULSE_DATASETS = [
    "original_qpos",
    "student_encoder_decoder_qpos",
    "teacher_qpos",
    "prior_deterministic_qpos",
    "prior_predicted_logvar_qpos",
    "prior_logvar_-2_qpos",
    "prior_logvar_0_qpos",
]

# Display-friendly names
DISPLAY_NAMES = {
    "original_qpos": "Original (Reference)",
    "student_encoder_decoder_qpos": "Student Encoder-Decoder",
    "teacher_qpos": "Teacher",
    "rgm_deterministic_qpos": "RGM (Deterministic)",
    "rgm_predicted_logvar_qpos": "RGM (Predicted logvar)",
    "rgm_logvar_-4_qpos": "RGM (logvar=-4)",
    "rgm_logvar_-3_qpos": "RGM (logvar=-3)",
    "rgm_logvar_-2_qpos": "RGM (logvar=-2)",
    "rgm_logvar_-1_qpos": "RGM (logvar=-1)",
    "rgm_logvar_-0.5_qpos": "RGM (logvar=-0.5)",
    "rgm_logvar_0_qpos": "RGM (logvar=0)",
    "prior_deterministic_qpos": "PULSE Prior (Deterministic)",
    "prior_predicted_logvar_qpos": "PULSE Prior (Predicted logvar)",
    "prior_logvar_-4_qpos": "PULSE Prior (logvar=-4)",
    "prior_logvar_-3_qpos": "PULSE Prior (logvar=-3)",
    "prior_logvar_-2_qpos": "PULSE Prior (logvar=-2)",
    "prior_logvar_-1_qpos": "PULSE Prior (logvar=-1)",
    "prior_logvar_-0.5_qpos": "PULSE Prior (logvar=-0.5)",
    "prior_logvar_0_qpos": "PULSE Prior (logvar=0)",
}

### RGM Rollouts

In [10]:
print(f"Rendering RGM rollouts for clip {CLIP_IDX}...\n")

for ds_name in RGM_DATASETS:
    display_name = DISPLAY_NAMES.get(ds_name, ds_name)
    qpos_traj = rgm_data[ds_name][CLIP_IDX]
    frames = render_qpos_trajectory(qpos_traj)
    print(f"{'=' * 50}")
    print(f"RGM — {display_name} ({qpos_traj.shape[0]} steps)")
    print(f"{'=' * 50}")
    media.show_video(frames, fps=RENDER_FPS)

Rendering RGM rollouts for clip 100...

RGM — Original (Reference) (250 steps)


This browser does not support the video tag.


RGM — Student Encoder-Decoder (490 steps)


This browser does not support the video tag.


RGM — RGM (Deterministic) (490 steps)


...

This browser does not support the video tag.


RGM — RGM (logvar=-2) (490 steps)


This browser does not support the video tag.


RGM — RGM (logvar=0) (490 steps)


This browser does not support the video tag.


### PULSE Rollouts

In [11]:
print(f"Rendering PULSE rollouts for clip {CLIP_IDX}...\n")

for ds_name in PULSE_DATASETS:
    display_name = DISPLAY_NAMES.get(ds_name, ds_name)
    qpos_traj = pulse_data[ds_name][CLIP_IDX]
    frames = render_qpos_trajectory(qpos_traj)
    print(f"{'=' * 50}")
    print(f"PULSE — {display_name} ({qpos_traj.shape[0]} steps)")
    print(f"{'=' * 50}")
    media.show_video(frames, fps=RENDER_FPS)

Rendering PULSE rollouts for clip 100...

PULSE — Original (Reference) (250 steps)


This browser does not support the video tag.


PULSE — Student Encoder-Decoder (490 steps)


This browser does not support the video tag.


PULSE — Teacher (490 steps)


...

This browser does not support the video tag.


PULSE — PULSE Prior (logvar=-2) (490 steps)


This browser does not support the video tag.


PULSE — PULSE Prior (logvar=0) (490 steps)


This browser does not support the video tag.


## Helper: Render Any Clip / Dataset

In [5]:
def render_and_show(source: str, dataset_name: str, clip_idx: int):
    """Render and display a single rollout.

    Args:
        source: "rgm" or "pulse".
        dataset_name: Key name in the H5 file (e.g. "rgm_logvar_-2_qpos").
        clip_idx: Clip index (0-841).
    """
    data_dict = rgm_data if source == "rgm" else pulse_data
    assert dataset_name in data_dict, f"{dataset_name} not in {source} data. Available: {sorted(k for k in data_dict if k.endswith('_qpos'))}"

    qpos_traj = data_dict[dataset_name][clip_idx]
    display_name = DISPLAY_NAMES.get(dataset_name, dataset_name)
    frames = render_qpos_trajectory(qpos_traj)
    print(f"{source.upper()} — {display_name} — clip {clip_idx} ({len(frames)} frames)")
    media.show_video(frames, fps=RENDER_FPS)


def render_comparison(clip_idx: int, rgm_key: str, pulse_key: str):
    """Render the same clip from both RGM and PULSE side by side (sequential videos).

    Args:
        clip_idx: Clip index (0-841).
        rgm_key: Dataset key from the RGM file.
        pulse_key: Dataset key from the PULSE file.
    """
    for source, key, data_dict in [("rgm", rgm_key, rgm_data), ("pulse", pulse_key, pulse_data)]:
        qpos_traj = data_dict[key][clip_idx]
        display_name = DISPLAY_NAMES.get(key, key)
        frames = render_qpos_trajectory(qpos_traj)
        print(f"{'=' * 50}")
        print(f"{source.upper()} — {display_name} — clip {clip_idx}")
        print(f"{'=' * 50}")
        media.show_video(frames, fps=RENDER_FPS)

In [7]:
# Example: compare deterministic generation across both models
render_comparison(100, "rgm_predicted_logvar_qpos", "prior_predicted_logvar_qpos")

# Example: render a single rollout
# render_and_show("rgm", "rgm_logvar_-2_qpos", clip_idx=200)
# render_and_show("pulse", "prior_logvar_-2_qpos", clip_idx=200)

NameError: name 'DISPLAY_NAMES' is not defined

---

## Arena Forage Inception Rollouts

Load and render qpos trajectories from the arena forage inception rollouts H5 file.

Datasets: `student_encoder_decoder_qpos`, `distill_prior_qpos`, `distill_prior_no_rgm_qpos`

In [12]:
ARENA_FORAGE_PATH = "/home/mila/a/aidan.sirbu/SCAMPER/data/arena_forage_rollout/arena_forage_inception_rollouts.h5"

arena_forage_data = load_h5_datasets(ARENA_FORAGE_PATH)

File: arena_forage_inception_rollouts.h5
  distill_prior_no_rgm_qpos: (842, 490, 74)
  distill_prior_qpos: (842, 490, 74)
  student_encoder_decoder_qpos: (842, 490, 74)



In [17]:
ARENA_FORAGE_DATASETS = [
    "student_encoder_decoder_qpos",
    "distill_prior_qpos",
    "distill_prior_no_rgm_qpos",
]

ARENA_FORAGE_DISPLAY_NAMES = {
    "student_encoder_decoder_qpos": "Student Encoder-Decoder",
    "distill_prior_qpos": "Distill Prior",
    "distill_prior_no_rgm_qpos": "Distill Prior (no RGM)",
}

In [18]:
# 10 clip indices to compare side by side
ARENA_FORAGE_CLIP_INDICES = [0, 50, 100, 200, 300, 400, 500, 600, 700, 800]

print(f"Rendering side-by-side: Distill Prior vs Distill Prior (no RGM)")
print(f"Clips: {ARENA_FORAGE_CLIP_INDICES}\n")

for clip_idx in ARENA_FORAGE_CLIP_INDICES:
    qpos_rgm = arena_forage_data["distill_prior_qpos"][clip_idx]
    qpos_no_rgm = arena_forage_data["distill_prior_no_rgm_qpos"][clip_idx]

    frames_rgm = render_qpos_trajectory(qpos_rgm)
    frames_no_rgm = render_qpos_trajectory(qpos_no_rgm)

    # Concatenate left (prior) and right (no RGM) into a single wide video
    num_frames = min(len(frames_rgm), len(frames_no_rgm))
    side_by_side = [
        np.concatenate([frames_rgm[i], frames_no_rgm[i]], axis=1)
        for i in range(num_frames)
    ]

    print(f"{'=' * 60}")
    print(f"Clip {clip_idx}  |  LEFT: Distill Prior  |  RIGHT: Distill Prior (no RGM)")
    print(f"{'=' * 60}")
    media.show_video(side_by_side, fps=RENDER_FPS)

Rendering side-by-side: Distill Prior vs Distill Prior (no RGM)
Clips: [0, 50, 100, 200, 300, 400, 500, 600, 700, 800]

Clip 0  |  LEFT: Distill Prior  |  RIGHT: Distill Prior (no RGM)


This browser does not support the video tag.


Clip 50  |  LEFT: Distill Prior  |  RIGHT: Distill Prior (no RGM)


This browser does not support the video tag.


Clip 100  |  LEFT: Distill Prior  |  RIGHT: Distill Prior (no RGM)


...

This browser does not support the video tag.


Clip 700  |  LEFT: Distill Prior  |  RIGHT: Distill Prior (no RGM)


This browser does not support the video tag.


Clip 800  |  LEFT: Distill Prior  |  RIGHT: Distill Prior (no RGM)


This browser does not support the video tag.


In [16]:
# Helper: render a single side-by-side for a given clip
def render_arena_forage_side_by_side(clip_idx: int):
    """Render distill_prior_qpos vs distill_prior_no_rgm_qpos side by side."""
    qpos_rgm = arena_forage_data["distill_prior_qpos"][clip_idx]
    qpos_no_rgm = arena_forage_data["distill_prior_no_rgm_qpos"][clip_idx]

    frames_rgm = render_qpos_trajectory(qpos_rgm)
    frames_no_rgm = render_qpos_trajectory(qpos_no_rgm)

    num_frames = min(len(frames_rgm), len(frames_no_rgm))
    side_by_side = [
        np.concatenate([frames_rgm[i], frames_no_rgm[i]], axis=1)
        for i in range(num_frames)
    ]

    print(f"Clip {clip_idx}  |  LEFT: Distill Prior  |  RIGHT: Distill Prior (no RGM)")
    media.show_video(side_by_side, fps=RENDER_FPS)


# Example usage:
# render_arena_forage_side_by_side(clip_idx=42)